# IBM HR analytics

In [9]:
#Import of the particular libraries 
import math
import numpy as np
import os 
import pandas as pd

In [10]:
from sklearn.ensemble import RandomForestClassifier
from sklearn.model_selection import train_test_split
from sklearn import metrics
from catboost import CatBoostClassifier

In [11]:
from evidently.dashboard import Dashboard
from evidently.tabs import ProbClassificationPerformanceTab

## Source data

In [13]:
DATA_DIR = "../../datasets/ibm-hr-analytics/" #full path to directory with the input data 
              
dataset_path = os.path.join(DATA_DIR, "WA_Fn-UseC_-HR-Employee-Attrition.csv")

In [14]:
dataset = pd.read_csv(dataset_path, sep = ',', header = 0)

In [15]:
dataset.head()

,Age,Attrition,BusinessTravel,DailyRate,Department,DistanceFromHome,Education,EducationField,EmployeeCount,EmployeeNumber,...,RelationshipSatisfaction,StandardHours,StockOptionLevel,TotalWorkingYears,TrainingTimesLastYear,WorkLifeBalance,YearsAtCompany,YearsInCurrentRole,YearsSinceLastPromotion,YearsWithCurrManager
0,41,Yes,Travel_Rarely,1102,Sales,1,2,Life Sciences,1,1,...,1,80,0,8,0,1,6,4,0,5
1,49,No,Travel_Frequently,279,Research & Development,8,1,Life Sciences,1,2,...,4,80,1,10,3,3,10,7,1,7
2,37,Yes,Travel_Rarely,1373,Research & Development,2,2,Other,1,4,...,2,80,0,7,3,3,0,0,0,0
3,33,No,Travel_Frequently,1392,Research & Development,3,4,Life Sciences,1,5,...,3,80,0,8,3,3,8,7,3,0
4,27,No,Travel_Rarely,591,Research & Development,2,1,Medical,1,7,...,4,80,1,6,3,3,2,2,2,2


In [16]:
dataset.describe()

,Age,DailyRate,DistanceFromHome,Education,EmployeeCount,EmployeeNumber,EnvironmentSatisfaction,HourlyRate,JobInvolvement,JobLevel,...,RelationshipSatisfaction,StandardHours,StockOptionLevel,TotalWorkingYears,TrainingTimesLastYear,WorkLifeBalance,YearsAtCompany,YearsInCurrentRole,YearsSinceLastPromotion,YearsWithCurrManager
count,1470.000000,1470.000000,1470.000000,1470.000000,1470.0,1470.000000,1470.000000,1470.000000,1470.000000,1470.000000,...,1470.000000,1470.0,1470.000000,1470.000000,1470.000000,1470.000000,1470.000000,1470.000000,1470.000000,1470.000000
mean,36.923810,802.485714,9.192517,2.912925,1.0,1024.865306,2.721769,65.891156,2.729932,2.063946,...,2.712245,80.0,0.793878,11.279592,2.799320,2.761224,7.008163,4.229252,2.187755,4.123129
std,9.135373,403.509100,8.106864,1.024165,0.0,602.024335,1.093082,20.329428,0.711561,1.106940,...,1.081209,0.0,0.852077,7.780782,1.289271,0.706476,6.126525,3.623137,3.222430,3.568136
min,18.000000,102.000000,1.000000,1.000000,1.0,1.000000,1.000000,30.000000,1.000000,1.000000,...,1.000000,80.0,0.000000,0.000000,0.000000,1.000000,0.000000,0.000000,0.000000,0.000000
25%,30.000000,465.000000,2.000000,2.000000,1.0,491.250000,2.000000,48.000000,2.000000,1.000000,...,2.000000,80.0,0.000000,6.000000,2.000000,2.000000,3.000000,2.000000,0.000000,2.000000
50%,36.000000,802.000000,7.000000,3.000000,1.0,1020.500000,3.000000,66.000000,3.000000,2.000000,...,3.000000,80.0,1.000000,10.000000,3.000000,3.000000,5.000000,3.000000,1.000000,3.000000
75%,43.000000,1157.000000,14.000000,4.000000,1.0,1555.750000,4.000000,83.750000,3.000000,3.000000,...,4.000000,80.0,1.000000,15.000000,3.000000,3.000000,9.000000,7.000000,3.000000,7.000000
max,60.000000,1499.000000,29.000000,5.000000,1.0,2068.000000,4.000000,100.000000,4.000000,5.000000,...,4.000000,80.0,3.000000,40.000000,6.000000,4.000000,40.000000,18.000000,15.000000,17.000000


## Feature engineering

In [17]:
target_name = 'Attrition'

In [18]:
numerique_features = ['Age', 'DailyRate', 'DistanceFromHome', 'Education', 'EnvironmentSatisfaction',
                      'HourlyRate', 'JobInvolvement', 'JobLevel', 'JobSatisfaction', 'MonthlyIncome',
                      'MonthlyRate', 'NumCompaniesWorked', 'PercentSalaryHike', 'PerformanceRating',
                      'RelationshipSatisfaction','StockOptionLevel', 'TotalWorkingYears',
                      'TrainingTimesLastYear', 'WorkLifeBalance', 'YearsAtCompany', 'YearsInCurrentRole',
                      'YearsSinceLastPromotion', 'YearsWithCurrManager'
                     ]

In [19]:
categorical_features = ['BusinessTravel', 'Department', 'EducationField', 'Gender',
                        'JobRole', 'MaritalStatus', 'OverTime'
                       ]

In [20]:
processed_dataset = dataset.copy(deep = True)

#### Drop constant features

In [21]:
processed_dataset.drop(columns = ['EmployeeCount', 'StandardHours', 'Over18'], inplace = True)

#### BusinessTravel

In [22]:
processed_dataset.BusinessTravel.value_counts()

Travel_Rarely        1043
Travel_Frequently     277
Non-Travel            150
Name: BusinessTravel, dtype: int64

In [23]:
business_travel_dummies = pd.get_dummies(processed_dataset.BusinessTravel, prefix = 'b_travel')
processed_dataset = pd.concat([processed_dataset, business_travel_dummies], axis=1)

#### Department

In [24]:
dataset.Department.value_counts()

Research & Development    961
Sales                     446
Human Resources            63
Name: Department, dtype: int64

In [25]:
department_dummies = pd.get_dummies(processed_dataset.Department, prefix = 'department')
processed_dataset = pd.concat([processed_dataset, department_dummies], axis=1)

#### EducationField

In [26]:
dataset.EducationField.value_counts()

Life Sciences       606
Medical             464
Marketing           159
Technical Degree    132
Other                82
Human Resources      27
Name: EducationField, dtype: int64

In [27]:
edu_field_dummies = pd.get_dummies(processed_dataset.Department, prefix = 'edu_field')
processed_dataset = pd.concat([processed_dataset, edu_field_dummies], axis=1)

#### Gender

In [28]:
dataset.Gender.value_counts()

Male      882
Female    588
Name: Gender, dtype: int64

In [29]:
processed_dataset['gender_bin'] = processed_dataset.Gender.apply(
    lambda x : 0 if x == 'Male' else 1 if x == 'Female' else -1)

#### JobRole

In [30]:
dataset.JobRole.value_counts()

Sales Executive              326
Research Scientist           292
Laboratory Technician        259
Manufacturing Director       145
Healthcare Representative    131
Manager                      102
Sales Representative          83
Research Director             80
Human Resources               52
Name: JobRole, dtype: int64

In [31]:
job_role_dummies = pd.get_dummies(processed_dataset.JobRole, prefix = 'job_role')
processed_dataset = pd.concat([processed_dataset, job_role_dummies], axis=1)

#### MaritalStatus

In [32]:
dataset.MaritalStatus.value_counts()

Married     673
Single      470
Divorced    327
Name: MaritalStatus, dtype: int64

In [33]:
marital_dummies = pd.get_dummies(processed_dataset.MaritalStatus, prefix = 'marital')
processed_dataset = pd.concat([processed_dataset, marital_dummies], axis=1)

#### OverTime

In [34]:
dataset.OverTime.value_counts()

No     1054
Yes     416
Name: OverTime, dtype: int64

In [35]:
overtime_dummies = pd.get_dummies(processed_dataset.OverTime, prefix = 'overtime')
processed_dataset = pd.concat([processed_dataset, overtime_dummies], axis=1)

In [36]:
#drop initial categorical features
processed_dataset.drop(columns = categorical_features, inplace = True)

### Target

In [37]:
processed_dataset['target'] = processed_dataset.Attrition.apply(
    lambda x : 0 if x == 'No' else 1 if x == 'Yes' else -1)

## Dataset generation

In [38]:
features = ['Age','DailyRate', 'DistanceFromHome', 'Education',
       'EmployeeNumber', 'EnvironmentSatisfaction', 'HourlyRate',
       'JobInvolvement', 'JobLevel', 'JobSatisfaction', 'MonthlyIncome',
       'MonthlyRate', 'NumCompaniesWorked', 'PercentSalaryHike',
       'PerformanceRating', 'RelationshipSatisfaction', 'StockOptionLevel',
       'TotalWorkingYears', 'TrainingTimesLastYear', 'WorkLifeBalance',
       'YearsAtCompany', 'YearsInCurrentRole', 'YearsSinceLastPromotion',
       'YearsWithCurrManager', 'b_travel_Non-Travel',
       'b_travel_Travel_Frequently', 'b_travel_Travel_Rarely',
       'department_Human Resources', 'department_Research & Development',
       'department_Sales', 'edu_field_Human Resources',
       'edu_field_Research & Development', 'edu_field_Sales', 'gender_bin',
       'job_role_Healthcare Representative', 'job_role_Human Resources',
       'job_role_Laboratory Technician', 'job_role_Manager',
       'job_role_Manufacturing Director', 'job_role_Research Director',
       'job_role_Research Scientist', 'job_role_Sales Executive',
       'job_role_Sales Representative', 'marital_Divorced', 'marital_Married',
       'marital_Single', 'overtime_No', 'overtime_Yes',]

#### Train & Holdout Test Split

In [39]:
RANDOM_STATE = 1603

In [40]:
train_data, test_data, train_y, test_y = train_test_split(processed_dataset[features], processed_dataset.target,
                                                   random_state = RANDOM_STATE, test_size = 0.25,
                                                   stratify = processed_dataset.target)

## Modeling

### Baseline

In [41]:
rf = RandomForestClassifier(n_estimators=500, n_jobs = -1, random_state = 11)

In [42]:
rf.fit(train_data[features], train_y)

RandomForestClassifier(n_estimators=500, n_jobs=-1, random_state=11)

### Baseline Classification Report

In [43]:
train_probas = pd.DataFrame(rf.predict_proba(train_data[features]))
train_probas.columns = ['no', 'yes']
test_probas = pd.DataFrame(rf.predict_proba(test_data[features]))
test_probas.columns = ['no', 'yes']

In [44]:
train_data.reset_index(inplace=True, drop=True)
train_data['Attrition'] = ['no' if x == 0 else 'yes' for x in train_y]
rf_merged_train = pd.concat([train_data, train_probas], axis = 1)

test_data.reset_index(inplace=True, drop=True)
test_data['Attrition'] = ['no' if x == 0 else 'yes' for x in test_y]
rf_merged_test = pd.concat([test_data, test_probas], axis = 1)

In [45]:
column_mapping = {}

column_mapping['target'] = 'Attrition'
column_mapping['prediction'] = ['yes', 'no']

column_mapping['numerical_features'] = ['Age','DailyRate', 'DistanceFromHome', 'Education',
       'EmployeeNumber', 'EnvironmentSatisfaction', 'HourlyRate',
       'JobInvolvement', 'JobLevel', 'JobSatisfaction', 'MonthlyIncome',
       'MonthlyRate', 'NumCompaniesWorked', 'PercentSalaryHike',
       'PerformanceRating', 'RelationshipSatisfaction', 'StockOptionLevel',
       'TotalWorkingYears', 'TrainingTimesLastYear', 'WorkLifeBalance',
       'YearsAtCompany', 'YearsInCurrentRole', 'YearsSinceLastPromotion',
       'YearsWithCurrManager']
column_mapping['categorical_features'] = ['b_travel_Non-Travel',
       'b_travel_Travel_Frequently', 'b_travel_Travel_Rarely',
       'department_Human Resources', 'department_Research & Development',
       'department_Sales', 'edu_field_Human Resources',
       'edu_field_Research & Development', 'edu_field_Sales', 'gender_bin',
       'job_role_Healthcare Representative', 'job_role_Human Resources',
       'job_role_Laboratory Technician', 'job_role_Manager',
       'job_role_Manufacturing Director', 'job_role_Research Director',
       'job_role_Research Scientist', 'job_role_Sales Executive',
       'job_role_Sales Representative', 'marital_Divorced', 'marital_Married',
       'marital_Single', 'overtime_No', 'overtime_Yes']

In [46]:
dashboard = Dashboard(tabs=[ProbClassificationPerformanceTab])
dashboard.calculate(rf_merged_train, rf_merged_test, column_mapping = column_mapping)
dashboard.show()

In [47]:
#dashboard.save('ibm_hr_attrition_baseline_performance.html')

## Better model

In [48]:
cat = CatBoostClassifier(random_state= 11, iterations=1600, learning_rate=0.008, class_weights = {0:1, 1:6})

In [49]:
cat.fit(train_data[features], train_y)

0:	learn: 0.6898542	total: 59.9ms	remaining: 1m 35s
1:	learn: 0.6885238	total: 63.1ms	remaining: 50.4s
2:	learn: 0.6861067	total: 66.5ms	remaining: 35.4s
3:	learn: 0.6831381	total: 70.2ms	remaining: 28s
4:	learn: 0.6800190	total: 74.4ms	remaining: 23.7s
5:	learn: 0.6774803	total: 78.7ms	remaining: 20.9s
6:	learn: 0.6740947	total: 82.8ms	remaining: 18.9s
7:	learn: 0.6705166	total: 89ms	remaining: 17.7s
8:	learn: 0.6682043	total: 93.9ms	remaining: 16.6s
9:	learn: 0.6651214	total: 98.1ms	remaining: 15.6s
10:	learn: 0.6622448	total: 102ms	remaining: 14.8s
11:	learn: 0.6595397	total: 106ms	remaining: 14.1s
12:	learn: 0.6573705	total: 110ms	remaining: 13.5s
13:	learn: 0.6555735	total: 115ms	remaining: 13s
14:	learn: 0.6527002	total: 119ms	remaining: 12.6s
15:	learn: 0.6508166	total: 124ms	remaining: 12.2s
16:	learn: 0.6473069	total: 128ms	remaining: 11.9s
17:	learn: 0.6454038	total: 132ms	remaining: 11.6s
18:	learn: 0.6436150	total: 136ms	remaining: 11.3s
19:	learn: 0.6413638	total: 141ms	re

163:	learn: 0.4642048	total: 2.03s	remaining: 17.8s
164:	learn: 0.4634200	total: 2.25s	remaining: 19.6s
165:	learn: 0.4623029	total: 2.39s	remaining: 20.7s
166:	learn: 0.4614066	total: 2.45s	remaining: 21s
167:	learn: 0.4605523	total: 2.59s	remaining: 22.1s
168:	learn: 0.4597796	total: 2.66s	remaining: 22.6s
169:	learn: 0.4587683	total: 2.74s	remaining: 23.1s
170:	learn: 0.4577834	total: 2.82s	remaining: 23.6s
171:	learn: 0.4568386	total: 2.92s	remaining: 24.2s
172:	learn: 0.4559663	total: 3.01s	remaining: 24.8s
173:	learn: 0.4549375	total: 3.08s	remaining: 25.3s
174:	learn: 0.4540637	total: 3.17s	remaining: 25.8s
175:	learn: 0.4533150	total: 3.31s	remaining: 26.8s
176:	learn: 0.4526356	total: 3.45s	remaining: 27.7s
177:	learn: 0.4511821	total: 3.59s	remaining: 28.7s
178:	learn: 0.4500344	total: 3.63s	remaining: 28.8s
179:	learn: 0.4495246	total: 3.68s	remaining: 29s
180:	learn: 0.4483727	total: 3.72s	remaining: 29.2s
181:	learn: 0.4476850	total: 3.77s	remaining: 29.4s
182:	learn: 0.44

354:	learn: 0.3484075	total: 5.74s	remaining: 20.1s
355:	learn: 0.3482534	total: 5.75s	remaining: 20.1s
356:	learn: 0.3477838	total: 5.75s	remaining: 20s
357:	learn: 0.3475210	total: 5.76s	remaining: 20s
358:	learn: 0.3471918	total: 5.77s	remaining: 19.9s
359:	learn: 0.3467089	total: 5.77s	remaining: 19.9s
360:	learn: 0.3463108	total: 5.78s	remaining: 19.8s
361:	learn: 0.3457645	total: 5.78s	remaining: 19.8s
362:	learn: 0.3452745	total: 5.78s	remaining: 19.7s
363:	learn: 0.3447160	total: 5.79s	remaining: 19.7s
364:	learn: 0.3442049	total: 5.79s	remaining: 19.6s
365:	learn: 0.3437263	total: 5.8s	remaining: 19.5s
366:	learn: 0.3432501	total: 5.8s	remaining: 19.5s
367:	learn: 0.3428339	total: 5.8s	remaining: 19.4s
368:	learn: 0.3424288	total: 5.81s	remaining: 19.4s
369:	learn: 0.3421470	total: 5.81s	remaining: 19.3s
370:	learn: 0.3415857	total: 5.82s	remaining: 19.3s
371:	learn: 0.3410508	total: 5.82s	remaining: 19.2s
372:	learn: 0.3405349	total: 5.82s	remaining: 19.2s
373:	learn: 0.34014

541:	learn: 0.2773148	total: 6.52s	remaining: 12.7s
542:	learn: 0.2770481	total: 6.53s	remaining: 12.7s
543:	learn: 0.2767063	total: 6.54s	remaining: 12.7s
544:	learn: 0.2763010	total: 6.55s	remaining: 12.7s
545:	learn: 0.2760235	total: 6.55s	remaining: 12.6s
546:	learn: 0.2757231	total: 6.55s	remaining: 12.6s
547:	learn: 0.2755312	total: 6.56s	remaining: 12.6s
548:	learn: 0.2752113	total: 6.56s	remaining: 12.6s
549:	learn: 0.2749168	total: 6.57s	remaining: 12.5s
550:	learn: 0.2746827	total: 6.57s	remaining: 12.5s
551:	learn: 0.2744052	total: 6.58s	remaining: 12.5s
552:	learn: 0.2739779	total: 6.58s	remaining: 12.5s
553:	learn: 0.2735100	total: 6.58s	remaining: 12.4s
554:	learn: 0.2731316	total: 6.59s	remaining: 12.4s
555:	learn: 0.2728206	total: 6.59s	remaining: 12.4s
556:	learn: 0.2724114	total: 6.59s	remaining: 12.3s
557:	learn: 0.2719782	total: 6.6s	remaining: 12.3s
558:	learn: 0.2716704	total: 6.6s	remaining: 12.3s
559:	learn: 0.2713354	total: 6.61s	remaining: 12.3s
560:	learn: 0.

726:	learn: 0.2261174	total: 7.36s	remaining: 8.84s
727:	learn: 0.2258139	total: 7.36s	remaining: 8.82s
728:	learn: 0.2255981	total: 7.37s	remaining: 8.8s
729:	learn: 0.2252912	total: 7.37s	remaining: 8.79s
730:	learn: 0.2250317	total: 7.38s	remaining: 8.77s
731:	learn: 0.2246660	total: 7.38s	remaining: 8.75s
732:	learn: 0.2243496	total: 7.39s	remaining: 8.74s
733:	learn: 0.2241645	total: 7.39s	remaining: 8.72s
734:	learn: 0.2239711	total: 7.39s	remaining: 8.7s
735:	learn: 0.2237817	total: 7.39s	remaining: 8.68s
736:	learn: 0.2234818	total: 7.4s	remaining: 8.66s
737:	learn: 0.2232358	total: 7.4s	remaining: 8.64s
738:	learn: 0.2228915	total: 7.4s	remaining: 8.63s
739:	learn: 0.2227033	total: 7.41s	remaining: 8.61s
740:	learn: 0.2224249	total: 7.41s	remaining: 8.59s
741:	learn: 0.2220861	total: 7.41s	remaining: 8.57s
742:	learn: 0.2218189	total: 7.42s	remaining: 8.55s
743:	learn: 0.2215086	total: 7.42s	remaining: 8.54s
744:	learn: 0.2212663	total: 7.42s	remaining: 8.52s
745:	learn: 0.220

892:	learn: 0.1862504	total: 7.88s	remaining: 6.24s
893:	learn: 0.1860268	total: 7.88s	remaining: 6.23s
894:	learn: 0.1858632	total: 7.89s	remaining: 6.21s
895:	learn: 0.1856662	total: 7.89s	remaining: 6.2s
896:	learn: 0.1854835	total: 7.9s	remaining: 6.19s
897:	learn: 0.1851860	total: 7.9s	remaining: 6.18s
898:	learn: 0.1849577	total: 7.91s	remaining: 6.17s
899:	learn: 0.1847473	total: 7.91s	remaining: 6.15s
900:	learn: 0.1845072	total: 7.92s	remaining: 6.14s
901:	learn: 0.1842877	total: 7.92s	remaining: 6.13s
902:	learn: 0.1840550	total: 7.92s	remaining: 6.12s
903:	learn: 0.1837473	total: 7.93s	remaining: 6.1s
904:	learn: 0.1834363	total: 7.93s	remaining: 6.09s
905:	learn: 0.1832577	total: 7.93s	remaining: 6.08s
906:	learn: 0.1830084	total: 7.94s	remaining: 6.06s
907:	learn: 0.1827608	total: 7.94s	remaining: 6.05s
908:	learn: 0.1824672	total: 7.94s	remaining: 6.04s
909:	learn: 0.1821746	total: 7.95s	remaining: 6.03s
910:	learn: 0.1820225	total: 7.95s	remaining: 6.01s
911:	learn: 0.18

1066:	learn: 0.1488189	total: 8.64s	remaining: 4.32s
1067:	learn: 0.1485436	total: 8.65s	remaining: 4.31s
1068:	learn: 0.1484463	total: 8.67s	remaining: 4.3s
1069:	learn: 0.1482412	total: 8.67s	remaining: 4.3s
1070:	learn: 0.1479810	total: 8.68s	remaining: 4.29s
1071:	learn: 0.1478641	total: 8.68s	remaining: 4.28s
1072:	learn: 0.1476545	total: 8.68s	remaining: 4.26s
1073:	learn: 0.1474913	total: 8.69s	remaining: 4.25s
1074:	learn: 0.1473702	total: 8.69s	remaining: 4.25s
1075:	learn: 0.1472387	total: 8.7s	remaining: 4.24s
1076:	learn: 0.1470031	total: 8.7s	remaining: 4.22s
1077:	learn: 0.1468475	total: 8.71s	remaining: 4.22s
1078:	learn: 0.1467407	total: 8.71s	remaining: 4.21s
1079:	learn: 0.1466252	total: 8.72s	remaining: 4.2s
1080:	learn: 0.1464253	total: 8.72s	remaining: 4.19s
1081:	learn: 0.1462914	total: 8.72s	remaining: 4.18s
1082:	learn: 0.1461495	total: 8.73s	remaining: 4.17s
1083:	learn: 0.1458953	total: 8.73s	remaining: 4.16s
1084:	learn: 0.1457541	total: 8.73s	remaining: 4.15

1266:	learn: 0.1144639	total: 9.39s	remaining: 2.47s
1267:	learn: 0.1143754	total: 9.4s	remaining: 2.46s
1268:	learn: 0.1143145	total: 9.41s	remaining: 2.45s
1269:	learn: 0.1142329	total: 9.41s	remaining: 2.45s
1270:	learn: 0.1141749	total: 9.42s	remaining: 2.44s
1271:	learn: 0.1140400	total: 9.42s	remaining: 2.43s
1272:	learn: 0.1138286	total: 9.43s	remaining: 2.42s
1273:	learn: 0.1136538	total: 9.43s	remaining: 2.41s
1274:	learn: 0.1135454	total: 9.43s	remaining: 2.4s
1275:	learn: 0.1133882	total: 9.44s	remaining: 2.4s
1276:	learn: 0.1133266	total: 9.44s	remaining: 2.39s
1277:	learn: 0.1131370	total: 9.44s	remaining: 2.38s
1278:	learn: 0.1129971	total: 9.45s	remaining: 2.37s
1279:	learn: 0.1129381	total: 9.45s	remaining: 2.36s
1280:	learn: 0.1127856	total: 9.45s	remaining: 2.35s
1281:	learn: 0.1125660	total: 9.46s	remaining: 2.35s
1282:	learn: 0.1124990	total: 9.46s	remaining: 2.34s
1283:	learn: 0.1123699	total: 9.46s	remaining: 2.33s
1284:	learn: 0.1122159	total: 9.46s	remaining: 2.

1449:	learn: 0.0911948	total: 9.96s	remaining: 1.03s
1450:	learn: 0.0911329	total: 9.96s	remaining: 1.02s
1451:	learn: 0.0910864	total: 9.97s	remaining: 1.02s
1452:	learn: 0.0909565	total: 9.97s	remaining: 1.01s
1453:	learn: 0.0909056	total: 9.98s	remaining: 1s
1454:	learn: 0.0907656	total: 9.98s	remaining: 995ms
1455:	learn: 0.0906346	total: 9.99s	remaining: 988ms
1456:	learn: 0.0904812	total: 9.99s	remaining: 981ms
1457:	learn: 0.0903612	total: 9.99s	remaining: 973ms
1458:	learn: 0.0902506	total: 10s	remaining: 966ms
1459:	learn: 0.0901195	total: 10s	remaining: 959ms
1460:	learn: 0.0900112	total: 10s	remaining: 952ms
1461:	learn: 0.0899016	total: 10s	remaining: 945ms
1462:	learn: 0.0898268	total: 10s	remaining: 937ms
1463:	learn: 0.0897310	total: 10s	remaining: 930ms
1464:	learn: 0.0896122	total: 10s	remaining: 923ms
1465:	learn: 0.0894516	total: 10s	remaining: 916ms
1466:	learn: 0.0893237	total: 10s	remaining: 909ms
1467:	learn: 0.0892206	total: 10s	remaining: 901ms
1468:	learn: 0.0

In [50]:
train_probas = pd.DataFrame(cat.predict_proba(train_data[features]))
train_probas.columns = ['no', 'yes']
test_probas = pd.DataFrame(cat.predict_proba(test_data[features]))
test_probas.columns = ['no', 'yes']

In [51]:
train_data.reset_index(inplace=True, drop=True)
train_data['target'] = ['no' if x == 0 else 'yes' for x in train_y]
cat_merged_train = pd.concat([train_data, train_probas], axis = 1)

test_data.reset_index(inplace=True, drop=True)
test_data['target'] = ['no' if x == 0 else 'yes' for x in test_y]
cat_merged_test = pd.concat([test_data, test_probas], axis = 1)

In [52]:
dashboard.calculate(cat_merged_train, cat_merged_test, column_mapping = column_mapping)
dashboard.show()

In [53]:
#dashboard.save('ibm_hr_attrition_better_model_performance.html')

## Models comparison

In [54]:
dashboard.calculate(rf_merged_test, cat_merged_test, column_mapping = column_mapping)
dashboard.show()

In [55]:
#dashboard.save('ibm_hr_attrition_model_comparison.html')